In [1]:
import os.path

import pandas as pd
import pickle as pkl
import numpy as np
import random
from tqdm import tqdm
import json
from sklearn import metrics
from custom_models.custom_model import BatchVectorizerClassifier
from ray import tune

/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/xgboost/compat.py:36: FutureWarning: pandas.Int64Index is deprecated and will be removed from pandas in a future version. Use pandas.Index with the appropriate dtype instead.
  from pandas import MultiIndex, Int64Index


In [ ]:
    model_types = ["hinge", "log", "modified_huber", "squared_hinge", "perceptron"]
    neg_to_pos_ratio = 1

    results_file = "results_titles_abstracts_linear.json"

    inputs = "titles_abstracts"

    filename_pos_human = "../data/pubmed_articles_pos_human.csv"
    filename_neg_human = "../data/pubmed_articles_neg_human.csv"

    with open("../data/cleaned_pos_neg_train_val_test_dataset_ids.pkl", "rb") as f:
        prop_typ_id_dict = pkl.load(f)

    ptypes = prop_typ_id_dict.keys()
#     ptypes = ["is_cohort", "is_guideline", "is_consensus", "is_qual", "is_ctprotocol"]

    for ptype in ptypes:
        pos_data_human = pd.read_csv(filename_pos_human, chunksize=100000)
        neg_data_human = pd.read_csv(filename_neg_human, chunksize=100000)

        sr_pos_train_ids = prop_typ_id_dict[ptype]["pos"]["train"]
        sr_neg_train_ids = prop_typ_id_dict[ptype]["neg"]["train"]

        sr_pos_val_ids = prop_typ_id_dict[ptype]["pos"]["val"]
        sr_neg_val_ids = prop_typ_id_dict[ptype]["neg"]["val"]

        sr_pos_test_ids = prop_typ_id_dict[ptype]["pos"]["test"]
        sr_neg_test_ids = prop_typ_id_dict[ptype]["neg"]["test"]

        sr_pos_train_set = pd.DataFrame()
        sr_pos_val_set = pd.DataFrame()
        sr_pos_test_set = pd.DataFrame()

        for pos_chunk in tqdm(pos_data_human):

            indices = pos_chunk.index
            indices = list(indices)

            pos_train_indices = list(
                set(indices).intersection(set(sr_pos_train_ids))
            )
            pos_val_indices = list(set(indices).intersection(set(sr_pos_val_ids)))
            pos_test_indices = list(set(indices).intersection(set(sr_pos_test_ids)))

            sr_pos_train_subset = pos_chunk.loc[pos_train_indices]
            if sr_pos_train_set.empty:
                sr_pos_train_set = pd.DataFrame(columns=sr_pos_train_set.columns)
            sr_pos_train_set = pd.concat([sr_pos_train_set, sr_pos_train_subset])

            sr_pos_val_subset = pos_chunk.loc[pos_val_indices]
            if sr_pos_val_set.empty:
                sr_pos_val_set = pd.DataFrame(columns=sr_pos_val_set.columns)
            sr_pos_val_set = pd.concat([sr_pos_val_set, sr_pos_val_subset])

            sr_pos_test_subset = pos_chunk.loc[pos_test_indices]
            if sr_pos_test_set.empty:
                sr_pos_test_set = pd.DataFrame(columns=sr_pos_test_set.columns)
            sr_pos_test_set = pd.concat([sr_pos_test_set, sr_pos_test_subset])

        sr_pos_train_set[ptype] = int(1)
        sr_pos_val_set[ptype] = int(1)
        sr_pos_test_set[ptype] = int(1)

        del pos_data_human
        del sr_pos_train_subset
        del pos_chunk
        del indices
        del sr_pos_train_ids

        sr_neg_train_ids_sample = random.sample(
            list(sr_neg_train_ids), round(len(sr_pos_train_set) * neg_to_pos_ratio)
        )

        sr_neg_train_set = pd.DataFrame()
        sr_neg_val_set = pd.DataFrame()
        sr_neg_test_set = pd.DataFrame()

        for neg_chunk in tqdm(neg_data_human):

            indices = neg_chunk.index
            indices = list(indices)
            neg_train_indices = list(
                set(indices).intersection(set(sr_neg_train_ids_sample))
            )
            neg_val_indices = list(set(indices).intersection(set(sr_neg_val_ids)))
            neg_test_indices = list(set(indices).intersection(set(sr_neg_test_ids)))
            sr_neg_subset = neg_chunk.loc[indices]

            sr_neg_train_subset = neg_chunk.loc[neg_train_indices]
            if sr_neg_train_set.empty:
                sr_neg_train_set = pd.DataFrame(columns=sr_neg_train_set.columns)
            sr_neg_train_set = pd.concat([sr_neg_train_set, sr_neg_train_subset])

            sr_neg_val_subset = neg_chunk.loc[neg_val_indices]
            if sr_neg_val_set.empty:
                sr_neg_val_set = pd.DataFrame(columns=sr_neg_val_set.columns)
            sr_neg_val_set = pd.concat([sr_neg_val_set, sr_neg_val_subset])

            sr_neg_test_subset = neg_chunk.loc[neg_test_indices]
            if sr_neg_test_set.empty:
                sr_neg_test_set = pd.DataFrame(columns=sr_neg_test_set.columns)
            sr_neg_test_set = pd.concat([sr_neg_test_set, sr_neg_test_subset])

        sr_neg_train_set[ptype] = int(0)
        sr_neg_val_set[ptype] = int(0)
        sr_neg_test_set[ptype] = int(0)

        del neg_data_human
        del sr_neg_subset
        del neg_chunk
        del indices

        sr_train_data = pd.concat([sr_neg_train_set, sr_pos_train_set]).sample(
            frac=1
        )
        del sr_neg_train_set
        del sr_pos_train_set
        sr_val_data = pd.concat([sr_neg_val_set, sr_pos_val_set]).sample(frac=1)
        del sr_neg_val_set
        del sr_pos_val_set
        sr_test_data = pd.concat([sr_neg_test_set, sr_pos_test_set]).sample(frac=1)
        del sr_neg_test_set
        del sr_pos_test_set

        y_train = sr_train_data[ptype]
        y_val = sr_val_data[ptype]
        y_test = sr_test_data[ptype]
        if inputs == "abstracts":
            X_train = sr_train_data["abstract_plaintext"]
            X_val = sr_val_data["abstract_plaintext"]
            X_test = sr_test_data["abstract_plaintext"]
        elif inputs == "titles":
            X_train = sr_train_data["title"]
            X_val = sr_val_data["title"]
            X_test = sr_test_data["title"]
        elif inputs == "titles_abstracts":
            X_train = pd.Series(
                [
                    "{0} {1}".format(train_title, train_abstract)
                    for train_title, train_abstract in zip(
                        sr_train_data["title"], sr_train_data["abstract_plaintext"]
                    )
                ]
            )
            X_val = pd.Series(
                [
                    "{0} {1}".format(val_title, val_abstract)
                    for val_title, val_abstract in zip(
                        sr_val_data["title"], sr_val_data["abstract_plaintext"]
                    )
                ]
            )
            X_test = pd.Series(
                [
                    "{0} {1}".format(test_title, test_abstract)
                    for test_title, test_abstract in zip(
                        sr_test_data["title"], sr_test_data["abstract_plaintext"]
                    )
                ]
            )

        del sr_train_data
        del sr_val_data
        del sr_test_data
        
        for model_type in model_types:
            

            config = {
                "loss": tune.grid_search([model_type]),
                "penalty": tune.grid_search(["l2", "l1", "elasticnet"]),
                "alpha": tune.grid_search(list(np.logspace(-10, -5, 20))),
            }

            def objective(config, data):
                bvc = BatchVectorizerClassifier(
                    loss=config["loss"],
                    penalty=config["penalty"],
                    alpha=config["alpha"],
                    l1_ratio=0.15,
                    fit_intercept=True,
                    max_iter=1000,
                    tol=0.001,
                    shuffle=True,
                    verbose=0,
                    epsilon=0.1,
                    n_jobs=None,
                    random_state=None,
                    learning_rate="optimal",
                    eta0=0.0,
                    power_t=0.5,
                    early_stopping=False,
                    validation_fraction=0.1,
                    n_iter_no_change=5,
                    class_weight=None,
                    warm_start=False,
                    average=False,
                )
                bvc.fit(data["X_train"], data["y_train"])
                y_pred_val = bvc.predict(data["X_val"])
                f1 = metrics.f1_score(y_pred_val, data["y_val"])

                tune.report(f1=f1)

                return {"f1": f1}

            data = {
                "X_train": X_train,
                "y_train": y_train,
                "X_val": X_val,
                "y_val": y_val,
            }
            analysis = tune.run(
                tune.with_parameters(objective, data=data),
                config=config,
                resources_per_trial={"gpu": 1},
                verbose=3,
            )

            best_config = analysis.get_best_config(metric="f1", mode="max")
            bvc = BatchVectorizerClassifier(
                loss=best_config["loss"],
                penalty=best_config["penalty"],
                alpha=best_config["alpha"],
                l1_ratio=0.15,
                fit_intercept=True,
                max_iter=1000,
                tol=0.001,
                shuffle=True,
                verbose=0,
                epsilon=0.1,
                n_jobs=None,
                random_state=None,
                learning_rate="optimal",
                eta0=0.0,
                power_t=0.5,
                early_stopping=False,
                validation_fraction=0.1,
                n_iter_no_change=5,
                class_weight=None,
                warm_start=False,
                average=False,
            )

            del analysis

            print("Fitting begins")
            bvc.fit(X_train, y_train)
            print("Fitting completed")

            print("Val inference begins")
            y_pred_val = bvc.predict(X_val)
            print("Val inference completed")

            print("Val metrics begins")
            recall_val = metrics.recall_score(y_val, y_pred_val, pos_label=1)
            spec_val = metrics.recall_score(y_val, y_pred_val, pos_label=0)
            precision_val = metrics.precision_score(y_val, y_pred_val)
            f1_val = metrics.f1_score(y_val, y_pred_val)
            accuracy_val = metrics.accuracy_score(y_val, y_pred_val)
            print("Val metrics completed")

            print("Test inference begins")
            y_pred_test = bvc.predict(X_test)
            print("Test inference completed")
            print("Test metrics begins")
            recall_test = metrics.recall_score(y_test, y_pred_test, pos_label=1)
            spec_test = metrics.recall_score(y_test, y_pred_test, pos_label=0)
            precision_test = metrics.precision_score(y_test, y_pred_test)
            f1_test = metrics.f1_score(y_test, y_pred_test)
            accuracy_test = metrics.accuracy_score(y_test, y_pred_test)
            print("Test metrics ends")

            results_dict = {
                "ptype": ptype,
                "model_type": model_type,
                "neg_to_pos_ratio": neg_to_pos_ratio,
                "best_penalty": best_config["penalty"],
                "best_alpha": best_config["alpha"],
                "recall_val": recall_val,
                "spec_val": spec_val,
                "precision_val_even": precision_val,
                "f1_val_even": f1_val,
                "accuracy_val": accuracy_val,
                "recall_test": recall_test,
                "spec_test": spec_test,
                "precision_test_even": precision_test,
                "f1_test_even": f1_test,
                "accuracy_test": accuracy_test,
            }

            if os.path.exists(results_file):
                with open(results_file, "r") as f_read:
                    results_list = json.load(f_read)
            else:
                results_list = []

            results_list.append(results_dict)
            with open(results_file, "w") as f_write:
                json.dump(results_list, f_write)

19it [00:24,  1.33s/it]/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/tqdm/std.py:1195: DtypeWarning: Columns (14) have mixed types. Specify dtype option on import or set low_memory=False.
  for obj in iterable:
51it [01:06,  1.31s/it]/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/tqdm/std.py:1195: DtypeWarning: Columns (14) have mixed types. Specify dtype option on import or set low_memory=False.
  for obj in iterable:
86it [01:51,  1.30s/it]
57it [01:26,  1.51s/it]
2024-01-20 22:33:50,380	WARNING function_runner.py:598 -- Function checkpointing is disabled. This may result in unexpected behavior when using checkpointing features or certain schedulers. To enable, set the train function arguments to be `func(config, checkpoint_dir=None)`.
2024-01-20 22:33:51,097	INFO trial_runner.py:803 -- starting objective_fbbfe_00000
(pid=2462055) /home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/xg

Trial name,status,loc,alpha,loss,penalty
objective_fbbfe_00000,RUNNING,10.151.122.12:2462055,1e-10,hinge,l2
objective_fbbfe_00001,PENDING,,1.83298e-10,hinge,l2
objective_fbbfe_00002,PENDING,,3.35982e-10,hinge,l2
objective_fbbfe_00003,PENDING,,6.15848e-10,hinge,l2
objective_fbbfe_00004,PENDING,,1.12884e-09,hinge,l2
objective_fbbfe_00005,PENDING,,2.06914e-09,hinge,l2
objective_fbbfe_00006,PENDING,,3.79269e-09,hinge,l2
objective_fbbfe_00007,PENDING,,6.95193e-09,hinge,l2
objective_fbbfe_00008,PENDING,,1.27427e-08,hinge,l2
objective_fbbfe_00009,PENDING,,2.33572e-08,hinge,l2


Result for objective_fbbfe_00000:
  date: 2024-01-20_22-33-55
  done: false
  experiment_id: 7d0c331b7482405188802027c1177199
  f1: 0.9086142322097378
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 2462055
  time_since_restore: 3.2303717136383057
  time_this_iter_s: 3.2303717136383057
  time_total_s: 3.2303717136383057
  timestamp: 1705790035
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: fbbfe_00000
  warmup_time: 0.0016629695892333984
  
Result for objective_fbbfe_00000:
  date: 2024-01-20_22-33-55
  done: true
  experiment_id: 7d0c331b7482405188802027c1177199
  experiment_tag: 0_alpha=1e-10,loss=hinge,penalty=l2
  f1: 0.9086142322097378
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 2462055
  time_since_restore: 3.2303717136383057
  time_this_iter_s: 3.2303717136383057
  time_total_s: 3.2303717136383057
  timestamp: 1705790035
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: fbbfe

2024-01-20 22:33:55,725	INFO trial_runner.py:803 -- starting objective_fbbfe_00001
(pid=2462091) /home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/xgboost/compat.py:36: FutureWarning: pandas.Int64Index is deprecated and will be removed from pandas in a future version. Use pandas.Index with the appropriate dtype instead.
(pid=2462091)   from pandas import MultiIndex, Int64Index


Result for objective_fbbfe_00001:
  date: 2024-01-20_22-33-59
  done: false
  experiment_id: e59156376e9a41cc94c38645aef2dc34
  f1: 0.909454227550893
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 2462091
  time_since_restore: 3.1921801567077637
  time_this_iter_s: 3.1921801567077637
  time_total_s: 3.1921801567077637
  timestamp: 1705790039
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: fbbfe_00001
  warmup_time: 0.0017685890197753906
  


...

Result for objective_5f0cf_00057:
  date: 2024-01-21_02-01-34
  done: true
  experiment_id: 17b1b011aafb408888e67c537fc002e4
  experiment_tag: 57_alpha=2.9764e-06,loss=perceptron,penalty=elasticnet
  f1: 0.9556227937468483
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 2516327
  time_since_restore: 3.13797926902771
  time_this_iter_s: 3.13797926902771
  time_total_s: 3.13797926902771
  timestamp: 1705802494
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: 5f0cf_00057
  warmup_time: 0.0017137527465820312
  


2024-01-21 02:01:35,113	INFO trial_runner.py:803 -- starting objective_5f0cf_00058
(pid=2516362) /home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/xgboost/compat.py:36: FutureWarning: pandas.Int64Index is deprecated and will be removed from pandas in a future version. Use pandas.Index with the appropriate dtype instead.
(pid=2516362)   from pandas import MultiIndex, Int64Index


Result for objective_5f0cf_00058:
  date: 2024-01-21_02-01-39
  done: false
  experiment_id: e47785271a23489b8dd063f2d96e1508
  f1: 0.9522847765715728
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 2516362
  time_since_restore: 3.1321940422058105
  time_this_iter_s: 3.1321940422058105
  time_total_s: 3.1321940422058105
  timestamp: 1705802499
  timesteps_since_restore: 0
  training_iteration: 1
  trial_id: 5f0cf_00058
  warmup_time: 0.001745462417602539
  
Result for objective_5f0cf_00058:
  date: 2024-01-21_02-01-39
  done: true
  experiment_id: e47785271a23489b8dd063f2d96e1508
  experiment_tag: 58_alpha=5.4556e-06,loss=perceptron,penalty=elasticnet
  f1: 0.9522847765715728
  hostname: pc09516
  iterations_since_restore: 1
  node_ip: 10.151.122.12
  pid: 2516362
  time_since_restore: 3.1321940422058105
  time_this_iter_s: 3.1321940422058105
  time_total_s: 3.1321940422058105
  timestamp: 1705802499
  timesteps_since_restore: 0
  training_iteration: 1

2024-01-21 02:01:40,113	INFO trial_runner.py:803 -- starting objective_5f0cf_00059
(pid=2516397) /home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/xgboost/compat.py:36: FutureWarning: pandas.Int64Index is deprecated and will be removed from pandas in a future version. Use pandas.Index with the appropriate dtype instead.
(pid=2516397)   from pandas import MultiIndex, Int64Index


Trial name,status,loc,alpha,loss,penalty,iter,total time (s),f1
objective_5f0cf_00059,RUNNING,10.151.122.12:2516397,1e-05,perceptron,elasticnet,,,
objective_5f0cf_00000,TERMINATED,10.151.122.12:2514333,1e-10,perceptron,l2,1,2.92899,0.952441
objective_5f0cf_00001,TERMINATED,10.151.122.12:2514368,1.83298e-10,perceptron,l2,1,2.9656,0.95316
objective_5f0cf_00002,TERMINATED,10.151.122.12:2514403,3.35982e-10,perceptron,l2,1,2.97381,0.954199
objective_5f0cf_00003,TERMINATED,10.151.122.12:2514438,6.15848e-10,perceptron,l2,1,2.94322,0.955969
objective_5f0cf_00004,TERMINATED,10.151.122.12:2514472,1.12884e-09,perceptron,l2,1,2.94393,0.953154
objective_5f0cf_00005,TERMINATED,10.151.122.12:2514507,2.06914e-09,perceptron,l2,1,2.93514,0.953957
objective_5f0cf_00006,TERMINATED,10.151.122.12:2514542,3.79269e-09,perceptron,l2,1,3.05786,0.953773
objective_5f0cf_00007,TERMINATED,10.151.122.12:2514577,6.95193e-09,perceptron,l2,1,2.92894,0.948721
objective_5f0cf_00008,TERMINATED,10.151.122.12:2514612,1.27427e-08,perceptron,l2,1,2.94128,0.953158
